<a href="https://colab.research.google.com/github/fmipython/PythonCourse2022/blob/main/04%20-%20Functional%20Programming/04%20-%20Functional%20Programming.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

# Функционално програмиране
План на лекцията:
- Какво е функционално програмиране ?
- Immutability & side-effects
- Функции като обекти
- Декоратори
- Анонимни (lambda) функции
- Lazy evaluation
- Generators
- Map
- Filter
- Reduce
- Zip
- List comprehension
- Скорост
- Dict comprehension
- Pattern matching
- Примери

## Какво е функционално програмиране ?

Функционалното програмиране е парадигма в програмирането, фокусираща се върху използването на функции. В езиците за функционално програмиране, функциите могат да се третират като обекти. Друга особенност на функционалното програмиране (или поне в чистата му форма), е липсата на състояние (а и от там, липсата на променливи в традиционния смисъл). В повечето езици за функционално програмиране липсват и класове. 

Основни концепции във функционалното програмиране:
- Функции като обекти
- Функции от по-висок ред
- "Чисти" функции
- Рекурсия 

Примери за езици, които следват единствено функционалната парадигма са Scheme, Haskell, Lisp.

В повечето модерни езици за програмиране могат да се открият елементи от функционалното програмиране - Python не е изключение. 


## Immutability и странични ефекти

### Накратко за mutable/immutable
По дефиниция, една променлива е `mutable`, ако можем да променим стойността ѝ, след като е създадена. Съответно `immutable` променлива, е променлива, на която не можем да променяме стойността. На практика, това означава, че стойността на една `immutable` променлива може да бъде задедена, само при създаването на променливата. 

В езици като C++ или Java, това е еквивалентно на дефинирането на променлива като константа. Тогава стойността ѝ е ясна по време на компилация.

### Накратко за страничните ефекти
Страничен ефект е когато променим състоянието на някоя променлива от дадена функция. Например нека разгледаме следната функция

In [9]:
def add_to_list(l):
    l.append(5)

l = []

add_to_list(l)
print(l)

add_to_list(l)
print(l)

[5]
[5, 5]


Тази функция, променя стойността на подадения аргумент `l`. Казваме, че тази функция съдържа страничен ефект. 

Страничните ефекти са силно използвани в обектно-ориентираното и процедурното програмиране, за разлика от функционалното програмиране. Както по-горе споменахме, в класическите езици за функционално програмиране, липсват променливи в познатия ни вид. Там можем да присвоим име на дадена стойност, без да я променяме повече. 

Функции, които не променят стойностите на променливи, се наричат "чисти". Във функционалното програмиране (а и не само), е прието всички функции да са чисти.

Можем да променим нашата функция `add` по следния начин, за да стане чиста:

In [10]:
def add_to_list(l):
    return l + [5]

l = []

l1 = add_to_list(l)
print(l1)

l2 = add_to_list(l)
print(l2)

print(l)

[5]
[5]
[]


## Функции, като обекти


В Python, функциите са т.нар. "first-class objects" - което на български може да се преведе като "първокласни обекти". А ако трябва да го обясним с прости думи, функциите могат да се третират като "нормалните" типове - числа, низове и т.н. Това означава, че можем да ги използваме като променливи - да им даваме имена, да ги подаваме към аргументи на други функции, да ги връщаме като резултат от функции и да ги пазим в колекции.

In [11]:
def multiply(a, b):
    return a * b

f = multiply

print(f(2, 3))

6


Важно е да направим разлика между `f = multiply` и `f = multiply()`. Макар и разликата да е малка синтактично, поведението на двата реда е различно. Първото извикване **присвоява функцията** към променливата `f`, докато второто **присвоява резултата от извикването** на функцията.  

Когато присвоим цялата функция (може да си го представяме като function pointer в C++), можем да ползваме функцията като нормална променлива:

In [12]:
def multiply(a, b):
    return a * b

def sum_(a, b):
    return a + b


def apply_to_numbers(a, b, f):
    print(f'Applying a function to {a} and {b}')
    return f(a, b)

print(apply_to_numbers(2, 3, sum_))
print(apply_to_numbers(2, 3, multiply))

Applying a function to 2 and 3
5
Applying a function to 2 and 3
6


А можем и да връщаме функция като резултат от друга функция:

In [13]:
def foo():
    print("Foo called")

def bar():
    return foo

f = bar()
f()

Foo called


В тялото на една функция, можем да дефинираме друга функция, която да върнем:

In [14]:
def foo():
    def bar():
        print("Bar called")
    
    return bar

f = foo()
f() 

Bar called


Освен като аргументи и резултат, функциите могат да се пазят и в колекции (списъци, речници, т.н.):

In [15]:
def add(a, b):
    return a + b

def subtract(a, b):
    return a - b

def multiply(a, b):
    return a * b

def divide(a, b):
    return a / b

actions = {
    '+': add,
    '-': subtract,
    '*': multiply,
    '/': divide
}

first = input('Enter a number: ')
operation = input('Enter an operation (+, -, * or /)')
second = input('Enter a number: ')

if operation not in actions:
    print('Operation not supported')
else:
    if not first.isnumeric() or not second.isnumeric():
        print('Input is not a number')
    else:
        first = int(first)
        second = int(second)

        result = actions[operation](first, second)
        print(f'{first} {operation} {second} = {result}')


1 + 2 = 3


## Декоратори

In [16]:
def log(f, *args, **kwargs):
    print(f'Calling {f} with {args} and {kwargs}')
    return f(*args, **kwargs)

def add(a, b):
    return a + b

print(log(add, 2, 3))

Calling <function add at 0x108abf060> with (2, 3) and {}
5


Има ли как да променим кода ни, така че всеки път когато извикваме `add`, всъщност да извикваме `log` с аргумент `add` ?

Python ни позволява много неща - всичко в Python е име, към което има прикрепен обект. Ние можем да променяме това какво седи зад дадено име.

In [17]:
def log(f, *args, **kwargs):
    print(f'Calling {f} with {args} and {kwargs}')
    return f(*args, **kwargs)

def add(a, b):
    return a + b


add = log

print(add(add, 2, 3))

Calling <function log at 0x108abeb90> with (2, 3) and {}
Calling 2 with (3,) and {}


TypeError: 'int' object is not callable

В този пример, просто преименуваме `add` на `log`. Проблемът е, че това се случва за всички срещания на `add`, и изпадаме в рекурсия с грешка.

Ами ако `log` приема само функцията, която искаме да изпълним, и ни връща нова функция, която вече да изпълнява подадената от нас функция ?

In [18]:
def log(f):
    def inner(*args, **kwargs):
        print(f'Calling {f} with {args} and {kwargs}')
        return f(*args, **kwargs)
    return inner

def add(a, b):
    return a + b


add = log(add)

print(add(2, 3))

Calling <function add at 0x108abf270> with (2, 3) and {}
5


Изглежда, че работи. Ние току-що имплементирахме функция "декоратор" в Python.
Декорирането на функции ни дава възможността да "закачим" нашата функция (ще наричаме декорирана) към друга такава (ще наричаме декорираща).
При всяко извикване на декорираната функция, реално ще извикваме декориращата функция. 

Видяхме, че това декориране се случва чрез промяната на името на функцията която искаме да декорираме, с извикването на декоратора. Python ни предоставя по-лесен и четим начин да направим същото действие, чрез следния синтаксис:

In [19]:
def log(f):
    def inner(*args, **kwargs):
        print(f'Calling {f} with {args} and {kwargs}')
        return f(*args, **kwargs)
    return inner

@log
def add(a, b):
    return a + b

print(add(2, 3))

Calling <function add at 0x108abf1c0> with (2, 3) and {}
5


Горните два примера са еднакви - единствената разлика е използването на декоратор синтаксиса в Python.

Можем да използваме един и същ декоратор върху няколко функции.

In [20]:
def log(f):
    def inner(*args, **kwargs):
        print(f'Calling {f} with {args} and {kwargs}')
        return f(*args, **kwargs)
    return inner

@log
def add(a, b):
    return a + b

@log 
def subtract(a, b):
    return a - b

@log
def multiply(a, b):
    return a * b

@log
def divide(a, b):
    return a / b

print(add(2, 3))
print(subtract(3, 1))
print(multiply(1.5, b=3))
print(divide(a=12, b=6))

Calling <function add at 0x108abef00> with (2, 3) and {}
5
Calling <function subtract at 0x108abf480> with (3, 1) and {}
2
Calling <function multiply at 0x108abf530> with (1.5,) and {'b': 3}
4.5
Calling <function divide at 0x108abf690> with () and {'a': 12, 'b': 6}
2.0


Друг пример за декоратор може да бъде декоратор, който измерва времето за изпълнение на функция:

In [21]:
import time

def time_it(f):
    def inner(*args, **kwargs):
        start = time.time()
        result = f(*args, **kwargs)
        end = time.time()
        print(f'{f} took {end - start:.2f} second')
    return inner

@time_it
def slow_function(a):
    return (a ** a) ** a

slow_function(1000)

<function slow_function at 0x108abf8a0> took 0.98 second


### Декоратори за напреднали

Python ни предоставя и възможността декораторите да приемат и аргументи.

Ако искаме да създадем декоратор с аргументи, то трябва да напишем функция, която приема тези аргументи, и връща декоратор.

In [22]:
def log(level):
    def wrap(f):
        def inner(*args, **kwargs):
            print(f'{level}: Calling {f} with {args} and {kwargs}')
            return f(*args, **kwargs)
        return inner
    return wrap

@log("Debug")
def add(a, b):
    return a + b

print(add(2, 3))

Debug: Calling <function add at 0x108abfab0> with (2, 3) and {}
5


Ако игнорираме синтактичната захар, горният пример би изглеждал по следния начин:

In [23]:
def a(level):
    def b(f):
        def c(*args, **kwargs):
            print(f'{level}: Calling {f} with {args} and {kwargs}')
            return f(*args, **kwargs)
        return c
    return b

def add(a, b):
    return a + b

add = log("Debug")(add)

a1 = a("Debug")
add = a1(add)

print(add(2, 3))

Debug: Calling <function log.<locals>.wrap.<locals>.inner at 0x108abfab0> with (2, 3) and {}
Debug: Calling <function add at 0x108abef00> with (2, 3) and {}
5


Ако имаме някаква "споделена" памет, можем да държим информация в нея, която да достъпваме през декоратора.

In [24]:
calls = {}
def count(f):
    def inner(*args, **kwargs):
        func_name = f.__name__
        if func_name not in calls:
            calls[func_name] = 0
        calls[func_name] += 1
        print(f'{func_name} has been called: {calls[func_name]} times. {calls=}')
        return f(*args, **kwargs)
    return inner

@count
def add(a, b):
    return a + b

@count 
def subtract(a, b):
    return a - b

@count
def multiply(a, b):
    return a * b

@count
def divide(a, b):
    return a / b

print(add(2, 3))
print(add(2, 3))
print(subtract(3, 1))
print(subtract(3, 1))
print(add(2, 3))


add has been called: 1 times. calls={'add': 1}
5
add has been called: 2 times. calls={'add': 2}
5
subtract has been called: 1 times. calls={'add': 2, 'subtract': 1}
2
subtract has been called: 2 times. calls={'add': 2, 'subtract': 2}
2
add has been called: 3 times. calls={'add': 3, 'subtract': 2}
5


### Декоратори и класове

Можем да декорираме и класове. Тук вместо да работи с функции, ще работим с класови обекти (class objects).

In [25]:
class Foo:
    def __init__(self):
        self.value = 0

f1 = Foo()
f1.value = 5
print(f'{f1.value=}')

f2 = Foo()
f2.value = 3
print(f'{f1.value=}')
print(f'{f2.value=}')

print(type(Foo))

f1.value=5
f1.value=5
f2.value=3
<class 'type'>


In [26]:
instances = {}
def singleton(cls):
    def inner(*args, **kwargs):
        if cls not in instances:
            instances[cls] = cls(*args, **kwargs)
        return instances[cls]
    return inner

@singleton
class Foo:
    def __init__(self):
        self.value = 0


f1 = Foo()
f1.value = 5
print(f'{f1.value=}')

f2 = Foo()
f2.value = 3
print(f'{f1.value=}')
print(f'{f2.value=}')
print(f1 is f2)


print(type(Foo))

f1.value=5
f1.value=3
f2.value=3
True
<class 'function'>


## Анонимни (lambda) функции

Lambda функции идват от т.нар ламбда смятане (lambda calculus) и изразяват изпълнението на дадени изчисления върху дадени стойности. Няма да навлизаме в математическите доказателства и формализми. Lambda функциите са анонимни функции - т.е. не се дефинират с `def` и без да е необходимо да им се дава име. 

Всяка ламбда функция има две основни части - входни променливи и един израз (expression). В Python, ламбда функциите се дефинират с ключовата дума `lambda`

In [27]:
lambda x: x + 1

<function __main__.<lambda>(x)>

По-горната функция приема един аргумент (на име `x`), и изпълнява израза `x + 1`. Важно е да се отбележи, че една ламбда функция може да съдържа само един израз.

Припомням, че израз в Python е всичко, което съдържа някакъв индетификатор (напр. променлива), литерал (напр. `'hello'`) или оператор (напр. извикване на функция, оператор `[]`)

Или казано по-просто: не може да създадем ламбда, която да присвоява стойност на някаква променлива:

In [28]:
lambda x: a = x

SyntaxError: cannot assign to lambda (2093076074.py, line 1)

Не можем също и да имаме два израза един след друг (Това чисто синтактично няма как да ни се позволи - ламбдите са на един ред, а в Python нямаме символ за край на израз.

Можем да извикваме дадена lambda функция, като просто използваме `()` след нея

In [29]:
(lambda x: print(x))(5)

5


Макар и анонимни, можем да присвоим ламбда функция към дадена променлива

In [30]:
f = lambda x: x + 1

print(f(5))

6


Горното парче код изпълнява следните стъпки:
1. Създава анонимна функция, която приема един аргумент (`x`) и връща стойноста на `x` събрана с 1
2. Присвояваме новосъздадената ни функция към променливата `f`
3. Принтираме резултата от извикването на `f` със стойност 5
    - В тялото на ламбда функцията, стойноста на `x` се замества с 5
    - От там, 5 + 1 = 6

Едно от местата, където често се ползват lambda функции, са вградените функции за сортиране. Както знаем, метода `.sort()` може да приема функция, която да сравнява обектите. 

In [31]:
l = [5, 2, 7, 3]
l.sort(key=lambda x: -x)
print(l)

[7, 5, 3, 2]


С помощта на тази ламбда, можем да сортираме числата в обратен ред. 

Можем да използваме ламбди за да сортираме и по-сложни списъци - например списък от наредени n-торки.

Нека е даден списък, съставен от имена на хора, и тяхната възраст. 

In [32]:
people_data = [('Иван', 22), ('Георги', 71), ('Мария', 35), ('Митко', 51), ('Любо', 35)]
people_data.sort(key=lambda person: (person[1], person[0]))
print(people_data)

[('Иван', 22), ('Любо', 35), ('Мария', 35), ('Митко', 51), ('Георги', 71)]


Тук първо сортираме хората по тяхната възраст, а после лексикографкси, по тяхното име.

Можем да използваме и функцията `sorted` с ламбда функция:

In [33]:
people_data = [('Иван', 22), ('Георги', 71), ('Мария', 35), ('Митко', 51), ('Любо', 35)]
print(sorted(people_data, key=lambda person: (person[1], person[0])))

[('Иван', 22), ('Любо', 35), ('Мария', 35), ('Митко', 51), ('Георги', 71)]


## Lazy evaluation

Съществуват различни стратегии за оценяване (или изчисляване) на изрази - най-позната е т.нар. "нетърпеливо оценяване" или "оценяване на момента" - целия израз се изчислява на момента.

Нека е даден израза `a + b + c`. Първо, ще бъде оценена стойността на `a`, после на `b`. Следващата стъпка е да се извърши операцията събиране. Резултатът от първата операция ще бъде използван за следващата операция събиране, заедно с `c`. 

Пример за оценяване на момента може да бъде следната функция:

In [34]:
def f(x):
    print(f'x = {x}')
    return x

print(f(1) + f(2))

x = 1
x = 2
3


При оценяването на момента (eager evaluation), всички необходими данни за извършване на изчислението (променливи, функции, др.) се зареждат наведнъж в паметта. Освен това, всички изчисления трябва да бъда извършени точно на момента.

Тук се намесва т.нар. "мързеливо" оценяване - изчисленията се извършват само при необходимост. Това ни позволява да си спестим някои изчисления (както и да работим с т.нар. "безкрайни" колекции).

Най-близкото до "мързеливо" оценяване, което познаваме е изчисляването на логическите изрази при `if` блокове и други булеви изрази - там, всеки елемент от израза се изчислява, при условие че предишния израз не е достатъчен за оценяване на целия израз (т.е. ако имаме един израз който е със стойност на `True` при изрази съдържащи `or`, тези след него не се оценяват. Ако имаме израз, който съдържа `and`, трябва да оценим всички стойности). 

По подобен начин работи и мързеливото оценяване, с разликата, че изразите се оценяват при поискване. 

## Generators

Генераторите са специални функции, които позволяват "мързеливо" итериране на дадена (дори и безкрайна) поредица. Генераторите не държат всичките си стойности в паметта, а изчисляват стойността при поискване (това позволява работата с "безкрайни" поредици).

Преди да се насочим към генераторите обаче, нека разгледаме концепцията за отложено изчисление.

Python ни позволява да спрем изпълнението на функция до дадено място, както и да продължим от това място нататък. За целта можем да използваме ключовата дума `yield`. Тя освен че спира функцията до даденото място, връща и стойност.

In [35]:
def delay_greeting():
    print("Preparing to say hello")
    yield "Hello!"
    print("Preparing to say this")
    yield "This"
    print("Preparing to say is")
    yield "is"
    print("Preparing to say a")
    yield "a"
    print("Preparing to say generator")
    yield "generator"

In [36]:
print(delay_greeting())

<generator object delay_greeting at 0x108ab1fc0>


Тук виждаме, че нашата функция вече ни връща `generator` обект. 

За да работим с нашия генератор обект, е необходимо да го подадем като обект на функцията `next` - тя ни връща следващия елемент от генератор/итератор.

In [37]:
delayed_greeting = delay_greeting()
print(next(delayed_greeting))
print(next(delayed_greeting))

Preparing to say hello
Hello!
Preparing to say this
This


In [38]:
print(next(delay_greeting()))
print(next(delay_greeting()))

Preparing to say hello
Hello!
Preparing to say hello
Hello!


Както се вижда, `next` изпълнява нашия код, до следващото срещане на `yield`, и връща стойността, която `yield` връща.

Можем да използваме `yield` и в цикли.

In [39]:
def few_numbers():
    for i in range(3):
        yield i

numbers = few_numbers()
print(next(numbers))
print(next(numbers))
print(next(numbers))
print(next(numbers))

0
1
2


StopIteration: 

Забелязваме, че при привършек на генератора се хвърля `StopIteration`. Това трябва да ни подсказва, че можем да използваме генератори в `for` цикли.

In [40]:
for number in few_numbers():
    print(number)

0
1
2


А можем и да имаме безкраен цикъл в генератор.

In [41]:
def fibonacci():
    previous = 1
    current = 1
    while True:
        yield current
        previous, current = current, current + previous
        


spiral = fibonacci()

print(next(spiral))
print(next(spiral))
print(next(spiral))
print(next(spiral))
print(next(spiral))

1
2
3
5
8


In [42]:
# Приключва в даден момент
for number in fibonacci():
    print(number)

1
2
3
5
8
13
21
34
55
89
144
233
377
610
987
1597
2584
4181
6765
10946
17711
28657
46368
75025
121393
196418
317811
514229
832040
1346269
2178309
3524578
5702887
9227465
14930352
24157817
39088169
63245986
102334155
165580141
267914296
433494437
701408733
1134903170
1836311903
2971215073
4807526976
7778742049
12586269025
20365011074
32951280099
53316291173
86267571272
139583862445
225851433717
365435296162
591286729879
956722026041
1548008755920
2504730781961
4052739537881
6557470319842
10610209857723
17167680177565
27777890035288
44945570212853
72723460248141
117669030460994
190392490709135
308061521170129
498454011879264
806515533049393
1304969544928657
2111485077978050
3416454622906707
5527939700884757
8944394323791464
14472334024676221
23416728348467685
37889062373143906
61305790721611591
99194853094755497
160500643816367088
259695496911122585
420196140727489673
679891637638612258
1100087778366101931
1779979416004714189
2880067194370816120
4660046610375530309
7540113804746346429
12

ValueError: Exceeds the limit (4300 digits) for integer string conversion; use sys.set_int_max_str_digits() to increase the limit

Използването на `yield` не е единствения начин да бъде създаден генератор. Python поддържа т.нар. "generator expressions". Generator expressions е синтактична конструкция, която ни позволява да създаваме генератор на базата на друга колекция/генератор. Синтактично, generator expression следва математическата нотация за дефиниране на множество:

$$ S = \{x^2 \mid x \in [1;100] , x \text{ is even}\} $$

Това математическо заклинание ни дава целите числа в диапазона от 1 до 100, които са четни, като всяко от тях е повдигнато на квадрат.

В общият случай, един generator expression изглежда по следния начин: `(f(x) for x in X if p(x))`, където `f` е функция, която прилагаме върху `x`, а `p` е филтрираща функция (повече за прилагането на функции върху елементи и филтрирането му по-долу)

Ако искаме да напишем generator expression, който ни връща буквите от азбуката, той би изглеждал по този начин:

In [43]:
import string

alphabet = (char for char in string.ascii_lowercase)

print(next(alphabet))
print(next(alphabet))
print(next(alphabet))

a
b
c


Ако пък искаме генератор на ASCII кодове, които са четни, той би изглеждал по този начин:

In [44]:
import string

alphabet = (ord(char) for char in string.ascii_lowercase if ord(char) % 2 == 0)

print(next(alphabet))
print(next(alphabet))
print(next(alphabet))

98
100
102


Една бележка за `next` - освен генератора, `next` приема и `default` стойност, която се връща при изчерпване на генератора:

In [45]:
def short_generator():
    for i in range(3):
        yield i

g = short_generator()

print(next(g, "Default"))
print(next(g, "Default"))
print(next(g, "Default"))
print(next(g, "Default"))
print(next(g, "Default"))

0
1
2
Default
Default


In [46]:
l = [2, 7, 5, 12, -3]

result = next(number for number in l if number % 5 == 0)

print(result)

5


## any и all

Два полезни метода, който работят с генератори са `any` и `all`:

- `any` - връща `True` ако поне една от стойностите в генератора е `True`.
- `all` - връща `True` ако всички стойности в генератора са `True`.

Това може да ни е полезно когато търсим в колекция по даден критерий.

In [47]:
grades = [3.20, 4.60, 6.00, 5.50, 4.75, 5.25]

is_full_mark_present = any(grade == 6.00 for grade in grades)
are_all_students_passing = all(grade >= 3.00 for grade in grades)

print(f"{is_full_mark_present=}")
print(f"{are_all_students_passing=}")

is_full_mark_present=True
are_all_students_passing=True


Пример от живия живот:

Имаме поредица от файлове и списък с шаблони. Ако даден файл съдържа един от шаблоните в името си, то той трябва да бъде игнориран.
Ето как може да използваме `any`/`all` за да постигнем целта си.

In [48]:
def filter_ignored_files_all(python_files):
    IGNORE_DIRS = ["venv", ".venv"]

    files = []
    for file in python_files:
        if all(ignore_path not in file for ignore_path in IGNORE_DIRS):
            files.append(file)
    
    return files

def filter_ignored_files_any(python_files):
    IGNORE_DIRS = ["venv", ".venv"]

    files = []
    for file in python_files:
        if not any(ignore_path in file for ignore_path in IGNORE_DIRS):
            files.append(file)
    
    return files

python_files = ["hello.py", "hw1.py", "venv/lib.py"]

print(filter_ignored_files_all(python_files))
print(filter_ignored_files_any(python_files))

['hello.py', 'hw1.py']
['hello.py', 'hw1.py']


## range и enumerate

Един от най-използваните генератори е `range`. `range` приема три аргумента - начало, край и стъпка. В резултат, получаваме генератор, който генерира числата от това множество. 

In [49]:
for i in range(2, 7, 2):
    print(i)

2
4
6


Няма значение колко е голям размера на `range`-а за представянето му - това е защото `range` изчислява следващия елемент на момента. 

Друг полезен генератор, е `enumerate`. Той приема колекция, и връща индексът на който се намира всеки елемент, както и самия елемент.

In [50]:
fruits = ["Apple", "Banana", "Cherry", "Watermelon", "Grapes"]

for i in range(len(fruits)):
    print(i, fruits[i])

0 Apple
1 Banana
2 Cherry
3 Watermelon
4 Grapes


In [51]:
fruits = ["Apple", "Banana", "Cherry", "Watermelon", "Grapes"]

for i, _ in enumerate(fruits):
    print(_)

Apple
Banana
Cherry
Watermelon
Grapes


Можем да използваме unpacking, за да разделим индекса и обекта:

In [52]:
fruits = ["Apple", "Banana", "Cherry", "Watermelon", "Grapes"]

for i, fruit in enumerate(fruits):
    print(f'{fruit} is on position {i}')

Apple is on position 0
Banana is on position 1
Cherry is on position 2
Watermelon is on position 3
Grapes is on position 4


Можем да зададем и начален индекс, от който да се отброява:

In [53]:
fruits = ["Apple", "Banana", "Cherry", "Watermelon", "Grapes"]

for i, fruit in enumerate(fruits, start=100):
    print(f'{fruit} is on position {i}')

Apple is on position 100
Banana is on position 101
Cherry is on position 102
Watermelon is on position 103
Grapes is on position 104


## Map



Map е специална функция, която има една-единствена цел - да приложи друга функция към всеки елемент от дадена колекция. Нека е даден списък с числа и функция, която приема число, и го умножава по 2.

In [54]:
numbers = [1, 2, 3, 4]

def square(number):
    return number ** 2

print(f'Appyling map directly returns: {map(square, numbers)}')

Appyling map directly returns: <map object at 0x108b61f00>


Важно е да се отбележи, че резултатът от map функцията е `map` обект - или поне така изглежда. Всъщност това, което се връща е генератор, който ни дава новите стойности. Съвсем лесно можем да превърнем този генератор в списък, с едно просто извикване на `list()` функцията.


In [55]:
numbers = [1, 2, 3, 4]

def square(number):
    return number ** 2

print(f'Converting the map object into a list: {list(map(square, numbers))}')

Converting the map object into a list: [1, 4, 9, 16]


Освен да подаваме нормална функция, можем да използваме и `lambda`.

In [56]:
numbers = [1, 2, 3, 4]

mapped_numbers = map(lambda number: number ** 2, numbers)
result = list(mapped_numbers)

print(result)

[1, 4, 9, 16]


Нека усложим нещата - ако се върнем на първоначалната ни дефиниция за `map` (Функция, която прилага друга функция върху колекция), си задаваме въпроса - какво става, ако имаме повече от една колекция, върху която искаме да приложим функция ? Възможно ли е въобще ? 

Отговора е да - `map` приема една или повече колекции. Единствената особенност е, че функцията която подаваме трябва да може да приеме повече от един аргумент. На по-прост език - ако подадем два списъка на `map`, функцията която ще се приложи върху тях трябва да приема два аргумента.

In [57]:
first_numbers = [1, 2, 3, 4]
second_numbers = [5, 6, 7, 8, 9]

def multiply(a, b):
    return a * b

print(list(map(multiply, first_numbers, second_numbers)))

[5, 12, 21, 32]


Важно е да се отбележи, че резултата от `map` операция винаги е **една** поредица от обекти - дори и да приемем 10 колекции, винаги на изхода ще имаме една. 

**Въпрос:** Как може да "измамим" системата, и да върнем повече от една колекция ?

### Отговор

Няма как да върнем повече от една колекция - това което можем да направим, е да върнем колекция, която съдържа наредени n-торки (tuples).

In [58]:
first_numbers = [1, 2, 3, 4]
second_numbers = [5, 6, 7, 8]

def return_as_tuple(a, b):
    return a, b

print(list(map(return_as_tuple, first_numbers, second_numbers)))

[(1, 5), (2, 6), (3, 7), (4, 8)]


## Zip

Нека се върнем за кратко към примера за използването на `map`, при който от два списъка, ние направихме един, който съдържаше елементите на двата, групирани по позицията им:

In [59]:
first_numbers = [1, 2, 3, 4]
second_numbers = [5, 6, 7, 8]

def return_as_tuple(a, b):
    return a, b

print(list(map(return_as_tuple, first_numbers, second_numbers)))

[(1, 5), (2, 6), (3, 7), (4, 8)]


В Python има готова функция, която прави това обединение за нас - `zip`

In [60]:
first_numbers = [1, 2, 3, 4]
second_numbers = [5, 6, 7, 8]

print(zip(first_numbers, second_numbers))
print(list(zip(first_numbers, second_numbers)))

[(1, 5), (2, 6), (3, 7), (4, 8)]


Не е нужно списъците да са от еднакви типове елементи.

In [61]:
names = ['Иван', 'Любо', 'Алекс']
favorite_number = [3, 20, 8]

print(list(zip(names, favorite_number)))

[('Иван', 3), ('Любо', 20), ('Алекс', 8)]


Ако единият списък е по-дълъг от другия, по-дългия списък ще бъде отрязан:

In [62]:
names = ['Иван', 'Любо', 'Алекс', 'Иво']
favorite_number = [3, 20, 7]

print(list(zip(names, favorite_number)))

[('Иван', 3), ('Любо', 20), ('Алекс', 7)]


In [63]:
names = ['Иван', 'Любо', 'Алекс']
favorite_number = [3, 20, 7, -1]

print(list(zip(names, favorite_number)))

[('Иван', 3), ('Любо', 20), ('Алекс', 7)]


Или поне това е поведението по подразбиране. `zip` предлага още два метода на работа. С помощта на аргумента `strict=True`, ако подадените списъци са с различен размер, `zip` ще ни хвърли грешка (това е въведено в Python3.10). 

In [64]:
names = ['Иван', 'Любо', 'Алекс']
favorite_number = [3, 20, 7, -1]

zip(names, favorite_number, strict=True)

А ако искаме да добавим някакви "празни" стойности към по-късия списък, може да използваме 

In [65]:
from itertools import zip_longest

names = ['Иван', 'Любо', 'Алекс']
favorite_number = [3, 20, 7, -1, -2]

print(list(zip_longest(names, favorite_number, fillvalue='Dummy')))

[('Иван', 3), ('Любо', 20), ('Алекс', 7), ('Dummy', -1), ('Dummy', -2)]


Ако трябва да сме на 100% коректни, `zip` приема каквато и да е колекция:

In [66]:
numbers = [1, 2, 3]
letters = ['a', 'b', 'c']

print(list(zip(map(lambda x: x ** 2, numbers), letters)))

[(1, 'a'), (4, 'b'), (9, 'c')]


Горният пример, малко по-културно разписан, изглежда по следния начин:

In [67]:
numbers = [1, 2, 3]
letters = ['a', 'b', 'c']

squared_numbers = map(lambda x: x ** 2, numbers)
zipped_together = zip(squared_numbers, letters)
zipped_together_as_a_list = list(zipped_together)

print(zipped_together_as_a_list)

[(1, 'a'), (4, 'b'), (9, 'c')]


## Filter


Както името подсказва, `filter` е функция която ни връща елементите от дадена колекция, удолетворяващи дадено условие.

Нека отново имаме някакви числа, и функция която връща дали дадено число е четно или не.

In [68]:
numbers = [2, 7, 11, 12]

def is_even(number):
    return number % 2 == 0

In [69]:
print(filter(is_even, numbers))

Както `map`, така и `filter` връщат генератор обекти - с едно извикване на `list` можем да превърнем резултата в списък

In [70]:
print(list(filter(is_even, numbers)))

[2, 12]


Може и с `lambda`

In [71]:
print(list(filter(lambda number: number % 2 == 0, numbers)))

[2, 12]


Ако искаме да вземем първия елемент от резултата на `filter`, може да използваме `next()`.

In [72]:
next(filter(lambda number: number % 2 == 0, numbers))

2

In [73]:
red_bull_team = "Verstappen", "Hadjar"
top10 = ["Leclerc", "Sainz", "Norris", "Piastri", "Russel", "Hülkenberg", "Verstappen", "Colapinto"]

next((driver for driver in top10 if driver in red_bull_team), "None")

'Verstappen'

## Reduce

Нека започнем с един пример: трябва да намерим произведението на всички числа в даден списък.

Нека за момент се абстрахираме от програмирането - как бихме намерили произведението на числа 3, 5 и 8 ? Първо бихме умножили 3 и 5, което прави 15. След това, получения резултат от предишната операция (в нашия случай 15) и ще го умножим с 8.

Тази процедура може да бъде използвана за списъци с произволен брой числа - всяко следващо число бива умножено с резултата до момента.

Ако трябва да представим тази идея с код, тя би изглеждала по следния начин:

In [74]:
def get_product_of_all_nums(nums):
    result = nums[0]

    for num in nums[1:]:
        result = result * num
    
    return result

In [75]:
numbers = [3, 5, 8]
print(get_product_of_all_nums(numbers))

120


Нека генерализираме нашата функция - вместо умножение, тя да може да работи с подадена функция, приемаща два аргумента - резултата до момента и текущото число

In [76]:
def my_reduce(function, collection):
    result = collection[0]

    for item in collection[1:]:
        result = function(result, item)
    
    return result

In [77]:
numbers = [3, 5, 8]
def multiply(result_so_far, current_number):
    return result_so_far * current_number

print(my_reduce(multiply, numbers))

120


Една промяна, която можем да направим е следната - вместо за начало да взимаме първия елемент от колекцията, може да приемаме началната стойност като аргумент на функцията. Така нашата функция би работела и с празни колекции. 

In [78]:
def my_reduce_with_start(function, collection, start):
    result = start

    for item in collection:
        result = function(result, item)
    
    return result

In [79]:
numbers = [3, 5, 8]
def multiply(result_so_far, current_number):
    return result_so_far * current_number

print(my_reduce_with_start(multiply, numbers, 1))

120


Ето че стигнахме и до `reduce` - функция, която приема функция и колекция. Функцията бива приложена върху резултата, който имаме до момента и всеки елемент от колекцията.
Важно е да уточним терминологията тук - в някои езици може да срещенете тази функция като `accumulate`, `fold` или пък `foldl`.

Тук е важно да спомена за наличието на т.нар "ляв" и "десен" `reduce`. В други функционални езици (като Haskell), имаме концепцията за ляв и десен `fold` - в каква посока се изпълнява функцията - отляво надясно или отдясно наляво. За някои операции (например умножение) реда на изпълнение няма значение, но например при деление би имало значение дали започваме от ляво или от дясно. Повече информация за fold функцията в другите езици, може да намерите [тук](https://www.wikiwand.com/en/Fold_(higher-order_function)). 

Вградената функция reduce в Python се намира в библиотеката `functools`. За да я използваме, първо трябва да я заредим (`import`)

In [80]:
from functools import reduce

numbers = [3, 5, 8]

def multiply(result_so_far, current_number):
    return result_so_far * current_number

print(reduce(multiply, numbers, 1))

120


Както може би сте се досетили, тук не получаваме генератор - резултатът от `reduce` е една стойност (в нашия случай това е число).

`reduce`, също както `map` и `filter` работи и с `lambda` функции. Тук е добро място да се отбележи, че първия аргумент, който бива подаден на функцията е стойността до момента (или стойността, която се е **акумулирала** (**accumulate**). 

In [81]:
numbers = [3, 5, 8]

print(reduce(lambda acc, number: acc * number, numbers))

120


А можем и да подадем начална стойност:

In [82]:
numbers = [3, 5, 8]
print(reduce(lambda acc, number: acc * number, numbers, 1))
print(reduce(lambda acc, number: acc * number, numbers, 2))

120
240


А сега един по-сложен пример: Нека имаме списък, чийто елементи са списъци с числа. С помощта на `reduce`, подходяща функция и подходяща начална стойност, бихме могли да получим един списък, който съдържа числата, без те да са в отделни списъци.

In [83]:
numbers_2d = [[1, 2, 3], [4, 5, 6], [7, 8, 9, 10]]


sum(numbers_2d, [])

[1, 2, 3, 4, 5, 6, 7, 8, 9, 10]

In [84]:
numbers_2d = [[1, 2, 3], [4, 5, 6], [7, 8, 9, 10]]

print(reduce(lambda acc, item: acc + item, numbers_2d, []))

[1, 2, 3, 4, 5, 6, 7, 8, 9, 10]


Припомням, че операция събиране (`+`) приложена върху два списъка ни връща конкатенацията на двата списъка. 

В горната операция, ние взехме един списък, и го "изравнихме" (flatten). Операцията "flatten" върху списъци е често срещата в езиците за функционално програмиране, макар и в Python да нямаме готова функция за това. 

In [85]:
g = [i for i in range(10, 21) if i % 2 == 0]

g

[10, 12, 14, 16, 18, 20]

## Sum

За наше улеснение, когато искаме да намерим сумата на списък с елементи, вместо да използваме `reduce`, можем да използваме функцията `sum`.

In [86]:
items = [1, 2, 3, 4, 5]

print(sum(items))

15


`sum` прилага оператор `+` върху елементите, което означава че работи и за други типове, освен `int`.

In [87]:
items = ["H", "e", "ll", "o", ",", " ", "w", "o", "r", "l", "d", "!"]

print(sum(items))

TypeError: unsupported operand type(s) for +: 'int' and 'str'

In [88]:
items = ["H", "e", "ll", "o", ",", " ", "w", "o", "r", "l", "d", "!"]

print(sum(items, start=""))

TypeError: sum() can't sum strings [use ''.join(seq) instead]

In [89]:
items = [[1, 2, 3], [4, 5, 6], [7, 8, 9, 10]]

print(sum(items, []))

[1, 2, 3, 4, 5, 6, 7, 8, 9, 10]


## List comprehension

В Python съществува функционалност, наречена "list comprehension". List comprehension е синтактична конструкция, която ни позволява да създаваме списъци на базата на други колекции/итератори/генератори. Синтактично, list comprehension прилича на generator expressions:

Можем да изразим тази идея в Python като използваме вече познатите ни `map` и `filter`:


In [90]:
numbers = range(1, 101)

even_numbers = filter(lambda x: x % 2 == 0, numbers)
squared_numbers = map(lambda x: x ** 2, even_numbers)

print(f'Squared even numbers: {list(squared_numbers)}')

Squared even numbers: [4, 16, 36, 64, 100, 144, 196, 256, 324, 400, 484, 576, 676, 784, 900, 1024, 1156, 1296, 1444, 1600, 1764, 1936, 2116, 2304, 2500, 2704, 2916, 3136, 3364, 3600, 3844, 4096, 4356, 4624, 4900, 5184, 5476, 5776, 6084, 6400, 6724, 7056, 7396, 7744, 8100, 8464, 8836, 9216, 9604, 10000]


В общия случай, синтаксиса на list comprehension е следния: `[f(item) for item in collection if p(item)]` - т.е. кода по-горе би изглеждал по следния начин като list comprehension:

In [91]:
print(f'Squared even numbers: {[x ** 2 for x in range(1, 101) if x % 2 == 0]}')

Squared even numbers: [4, 16, 36, 64, 100, 144, 196, 256, 324, 400, 484, 576, 676, 784, 900, 1024, 1156, 1296, 1444, 1600, 1764, 1936, 2116, 2304, 2500, 2704, 2916, 3136, 3364, 3600, 3844, 4096, 4356, 4624, 4900, 5184, 5476, 5776, 6084, 6400, 6724, 7056, 7396, 7744, 8100, 8464, 8836, 9216, 9604, 10000]


`if` часта или функцията, която се прилага върху всяка променливата могат да бъдат изпуснати:

In [92]:
numbers = [1, 2, 3]
print(f'Odd numbers: {[number for number in numbers if number % 2 != 0]}')
print(f'Multiplying all numbers by 2: {[number * 2 for number in numbers]}')

Odd numbers: [1, 3]
Multiplying all numbers by 2: [2, 4, 6]


Тук е добре да отбележем, че основната синтактична разлика между list comprehension и generator comprehension е скобите (`[]` за list comprehension и `()` за generator comprehension)

In [93]:
l = ['a', 'b', 'c', 'D', 'e']

result = []

for letter in l:
    if letter.isupper():
        item = letter.lower()
        result.append(ord(item))

result



[100]

In [94]:
l = ['a', 'b', 'c', 'D', 'e']

def transform_letter(letter):
    item = letter.lower()
    return ord(item)


[transform_letter(letter) for letter in l if letter.isupper()]

[100]

In [95]:
def calculate_area_of_rectangle(a, b):
    return a * b

rectangles = [(1, 2), (5, 4), (3, 2.5), (-2, 3)]
areas = [calculate_area_of_rectangle(x, y) for x, y in rectangles if x >= 0 and y >= 0]

print(f'Areas of valid rectangles: {areas}')

Areas of valid rectangles: [2, 20, 7.5]


Може би забелязвате, че когато функцията която изпълняваме не е външна, не използваме `lambda`, а директно пишем операцията която искаме да приложим - това е част от опростяването на синтаксиса на list comprehension-ите. 

Нека имаме дадени числа - искаме да върнем списък, в който за всяко число да пише "Yes" ако се дели на 3 или 5 и "No" в противен случай. Това може да стане лесно, чрез използването на тернарния оператор в Python.

In [96]:
numbers = [7, 12, 5, 6, 9, 15, 1, 11, -3]

results = [
    "Yes" 
        if number % 3 == 0 or number % 5 == 0 
    else "No"
    for number in numbers
    if number > 0
]

print(f'Results are: {results}')

Results are: ['No', 'Yes', 'Yes', 'Yes', 'Yes', 'Yes', 'No', 'No']


## Скорост

Едно от най-"шокиращите" неща в Python е скоростта, която получаваме при използването на обикновенни `for` цикли, `map` или list comprehension.

За да демонстрираме разликата, ще създадем функция, която повдига число на квадрат, и ще я приложим върху списък от 40 000 000 числа.

In [97]:
from time import time

time()

1792926904.0654159

In [98]:
from time import time

def power_up(a):
    return a ** 2

numbers = list(range(1, 40_000_000))

for_loop_start = time()

for_loop_result = []
for number in numbers:
    for_loop_result.append(power_up(number))

for_loop_end = time()
print(f'For-looping took {for_loop_end - for_loop_start:.2f} seconds')


map_start = time()

map_result = list(map(power_up, numbers))

map_end = time()
print(f'map() took {map_end - map_start:.2f} seconds')


list_comprehension_start = time()

list_comprehension_result = [power_up(x) for x in numbers]

list_comprehension_end = time()
print(f'List comprehension took {list_comprehension_end - list_comprehension_start:.2f} seconds')

For-looping took 3.83 seconds
map() took 2.27 seconds
List comprehension took 2.19 seconds


Основната разлика във времето идва от факта, че `append()` операцията е бавна. `map` и list comprehension-ите използва хитрини при заделянето на паметта, затова може да се каже че са с около 30% по-бързи. Няма да се впускам повече в темата, за по-любопитните, [тук](https://web.archive.org/web/20190319205826/http://blog.cdleary.com/2010/04/efficiency-of-list-comprehensions/) нещата са обяснение в повече детайли.

На въпросът, кой от трите подхода се използват, моят отговор е следния: list comprehension и `map` дават доста по-добро представяне спрямо `for` loop + `append`, затова и са за предпочитане. Синтаксисът на list comprehension-ите е по-прост спрямо този на `map` (особенно ако трябва и да филтрираме елементите), което води до това, че **list comprehension-ите са за предпочитане**.

## Dict comprehension

Подобно на list comprehension, можем да използваме подобен запис да създадем и речник (dictionary, dict).

Синтаксисът е същият, само че вместо `[]`, използваме `{}`. Също така, вместо един елемент, използваме `key:value` - т.е. общия вид би изглеждал по следния начин: `{f(item):g(value) for item in collection if p(item)}`

Нека като пример разглеждаме dict, който съдържа число (измежду 1 и 10), и дали е четно или не

In [99]:
my_dict = {num:num%2 == 0 for num in range(1, 11)}

print(my_dict)

{1: False, 2: True, 3: False, 4: True, 5: False, 6: True, 7: False, 8: True, 9: False, 10: True}


Както при generator изразите и list comprehension, можем да добавим `if` част.

Нека създадем речник, който съдържа четните числа от 1 до 20, както и тяхната репрезентация като низ.

In [100]:
even_numbers_as_strs = {num:str(num) for num in range(1, 21) if num % 2 == 0}

print(even_numbers_as_strs)

{2: '2', 4: '4', 6: '6', 8: '8', 10: '10', 12: '12', 14: '14', 16: '16', 18: '18', 20: '20'}


## Walrus operator

В Python 3.8 се появява нов оператор, който ни позволява да имаме т.нар. "assignment expression" - израз, в който можем да присвояваме променливи.

Чрез него можем да спестим изчисляването на дадени изрази, като ги присвоим към име на места, в който това не бе позволено.

In [101]:
numbers = [4, 7, 6, 3, 1, 8]

data = {
    'count': len(numbers),
    'sum': sum(numbers),
    'average': sum(numbers) / len(numbers)
}

data

{'count': 6, 'sum': 29, 'average': 4.833333333333333}

Тук, изчисляваме дължината и сумата на елементите два пъти. Можем да отделим тези сметки в променливи, и да ги преизползваме.

In [102]:
numbers = [4, 7, 6, 3, 1, 8]

count = len(numbers)
total_sum = sum(numbers)

data = {
    'count': count,
    'sum': total_sum,
    'average': total_sum / count
}

data

{'count': 6, 'sum': 29, 'average': 4.833333333333333}

Проблемът тук е, че използваме тези променливи само за речника. Можем да "преместим" това дефиниране на стойностите вътре в речника, чрез използването на walrus оператора. 

Той изглежда по следният начин: `(name := expression)`. Важно е да се отбележи, че скобите са задължителни.

In [103]:
numbers = [4, 7, 6, 3, 1, 8]

data = {
    'count': (count := len(numbers)),
    'sum': (total_sum := sum(numbers)),
    'average': total_sum / count
}

data

{'count': 6, 'sum': 29, 'average': 4.833333333333333}

Най-честото използване на walrus оператора е в list comprehension-и.

В долният пример имаме клас `Point`, както и функция `calculate_length`, която изчислява разстоянието между две точки.

Дадени са ни 4 точки, като искаме да върнем точките и разстоянието между тях, ако то е по-малко от 3.

In [104]:
import math

class Point:
    def __init__(self, x, y):
        self.x = x
        self.y = y

    def __str__(self):
        return f'({self.x}, {self.y})'
    
    def __repr__(self):
        return str(self)

def calculate_length(a, b):
    return math.sqrt((a.x - b.x) ** 2 + (a.y - b.y) ** 2)

point_1 = Point(2, 3)
point_2 = Point(3, 4)
point_3 = Point(4, 5)
point_4 = Point(1, 0)

first_points = [point_1, point_2]
second_points = [point_3, point_4]

In [105]:
distances = [(first, second, calculate_length(first, second)) for first, second in zip(first_points, second_points) if calculate_length(first, second) > 3]
distances

[((3, 4), (1, 0), 4.47213595499958)]

Прилагайки walrus оператора тук, кодът ни изглежда по следния начин:

In [106]:
distances = [(first, second, length) for first, second in zip(first_points, second_points) if (length := calculate_length(first, second)) > 3]
distances

[((3, 4), (1, 0), 4.47213595499958)]

Друго използване на walrus оператора е при функции, които връщат резултат или `None`.

In [107]:
from random import choice

AVAILABLE_SERVERS = ["Magma", "Terra", "Fortitude", "Mars", "Sirius"]
load = 23

def get_available_server():
    server = choice(AVAILABLE_SERVERS)

    if load >= 75:
        return None

    return server


if (server := get_available_server()):
    print(f"Available server: {server}")
else:
    print("No server available")


Available server: Magma


## namedtuple

В горният пример, дефинирахме клас `Point`, който единствено държи две стойности - `x` и `y`. Към него липсват методи (освен `__str__` и `__repr__`). 

Алтернативен вариант би бил да представим нашата точка като `tuple`. 

In [108]:
point_1 = (2, 3)

print(f'({point_1[0]}, {point_1[1]})')

(2, 3)


Проблемът с този подход, е че трябва да гадаем на какво отговоря всеки от елементите на tuple-а. 

Python ни позволява да създадем т.нар. именувана n-торка (`namedtuple`). Този тип е подтип на `tuple`, но с избрано име от нас, и именувани член-данни.

Можем да създадем `namedtuple` по следния начин:

In [109]:
from collections import namedtuple
Point = namedtuple('Point', ['x', 'y'])

point_1 = Point(2, 3)

point_1.x += 1
print(f'({point_1.x}, {point_1.y})')
print(point_1)

AttributeError: can't set attribute

Забелязваме, че `namedtuple` има предефиниран `__str__` и `__repr__` методи.

## Pattern matching и `match` израза

Pattern matching-а (или шаблонното съпоствяне на български) е една от най-полезните функционалности в езиците за функционално програмиране. Тя ни позволява да проверяваме дали даден обект отговаря на даден шаблон, и да извличаме данни от него.

В Python3.10 за първи път се появява възможността на pattern matching. Тя е реализирана чрез `match` израза.

Общият вид на `match` конструкцията изглежда по следния начин:

```python
match <обект>:
    case <условие> <guard>:
        тяло
    case <условие2>:
        тяло
    case <условие3> <guard>:
        тяло
    ...
```

### Прости примери

Нека напишем кратка програма калкулатор. Потребителят ще въведе две числа от клавиатурата и операция, която да се извърши.

In [110]:
first_number = int(input('Enter the first number: '))
second_number = int(input('Enter the second number: '))

operation = input('Enter an operation (+, -, * or /)')

match operation:
    case '+':
        result = first_number + second_number
    case '-':
        result = first_number - second_number
    case '*':
        result = first_number * second_number
    case '/':
        result = first_number / second_number
    case _:
        print('Operation not supported')

print(f'{first_number} {operation} {second_number} = {result}')

12 + 13 = 25


Какво се случва тук ? Прочитаме две числа и операция която да се извърши върху тях. След това подаваме операцията на `match` израза.

Оттам, започваме да сравняваме `operation` с различните възможности. Ако `operation` съвпада с някой от `case`-овете, изпълняваме съответното тяло.

Важна забележка - `_` винаги съвпада с всичко. Това ни позволява да си направим "default" клауза, която да се изпълни, ако няма друга която да се съвпада.

На мястото на `<обект>` можем да поставим и обект от тип `tuple`:

In [111]:
numbers = (5, 3)


match numbers:
    case (1, 2):
        print('First case')
    case (3, 3):
        print('Second case')
    case (5, 3):
        print('Third case')
    case _:
        print('Default case')

Third case


Тук `numbers` се оценява спрямо всички възможни случаи. Първият който съвпада, е `(5, 3)`, и съответно се изпълнява тялото на съответния `case`.


С помощта на `_` можем да укажем че не ни интересува конкретната стойност на даден елемент от tuple-а.

In [112]:
numbers = (5, 3)

match numbers:
    case (2, 5) | (5, 3):
        print('First case')
    case (5, _):
        print('Second case')
    case _:
        print('Default case')

First case


В тази ситуация, `match` изразът ще изпълни първия случай, защото той е първия който съвпада.

### По-сложни примери

Силата на `match` израза идва в това какви изрази поддържа. Ще разгледаме някои от тях:

#### Or pattern

In [113]:
numbers = (5, 3)

match numbers:
    case (5, 3) | (2, 4):
        print('First case')
    case (5, 3):
        print('Second case')
    case _:
        print('Default case')

First case


In [114]:
numbers = (2, 4)

match numbers:
    case (5, 3) | (2, 4):
        print('First case')
    case (5, 3):
        print('Second case')
    case _:
        print('Default case')

First case


`or` pattern-ът ни позволява да сравняваме даден обект с няколко условия. Той се използва с `|` оператора.

При сравнението се проверява дали подадения израз съвпада с първата или втората част от `case`-а.

#### As pattern

Ако искаме да проверим кое точно от pattern-ите съвпада, можем да използваме конструкцията `as`:

In [115]:
numbers = (5, 3)

match numbers:
    case (5, 3) | (2, 4) as a:
        print(f'First case: {a}')
    case (5, 3):
        print('Second case')
    case _:
        print('Default case')

First case: (5, 3)


Тук, след като `case`-а съвпадне, стойността на numbers ще бъде присвоена на `x`.

In [116]:
numbers = (2, 4)

match numbers:
    case (5, 3) | (2, 4) as a:
        print(f'First case: {a}')
    case (5, 3):
        print('Second case')
    case _:
        print('Default case')

First case: (2, 4)


In [117]:
numbers = (2, 4)

match numbers:
    case (2 as a, 4 as b):
        print(f'First case: {a}')
    case (5, 3):
        print('Second case')
    case _:
        print('Default case')

First case: 2


#### Value pattern

In [118]:
def divide(x, y):
    if y == 0:
        return None
    
    return x / y

match divide(10, 2):
    case None:
        print('Division by zero')
    case result:
        print(f'Result is {result}')


Result is 5.0


Можем да сравняваме и спрямо конкретни стойности - можем да проверяваме дали даден обект е None, или някакъв друг литерал

`type` pattern-ът ни позволява да сравняваме спрямо типа на дадения обект. В примера, функцията `divide(10, 2)` ще върне `int``, което ще се присвои на `result`.

#### Sequence pattern

In [119]:
numbers = [1, 2, 3, 4, 5]

match numbers:
    case [1, 2, 3]:
        print('First case')
    case [1, 2, 3, 4, 5]:
        print('Second case')

Second case


In [120]:
numbers = [1, 2, 3, 4, 5]

match numbers:
    case [1, 2, 3, *rest]:
        print(f'First case, {rest=}')
    case [1, 2, 3, 4, 5]:
        print('Second case')

First case, rest=[4, 5]


In [121]:
numbers = [1, 2, 3, 4, 5]

match numbers:
    case [1, 2, *_, 5]:
        print(f'First case')

First case


### Guard-ове

`match` израза ни позволява да добавяме и условия, които да се проверяват след като съвпадне pattern-а (т.нар guard-ове).

Те се добавят след шаблона в case частта.

In [122]:
numbers = (5, 3)
some_other_value = 42

match numbers:
    case (5, 3):
        print('First case')
    case (5, 3):
        print('Second case')
    case _:
        print('Default case')

First case


In [123]:
numbers = (5, 3)

match numbers:
    case (a, b) if a == 5:
        print('First case')
    case _:
        print('Default case')

First case


### Class pattern

Можем да прилагаме `match` върху инстанции на класове. За целта, трябва да подадем името на класа, последвани от стойностите за атрибутите му.

In [124]:
class Point:
    def __init__(self, a, b, c):
        self.x = a
        self.y = b
        self.z = c

point = Point(2, 3, 4)

match point:
    case Point(x=0, y=0):
        print("Point at the origin")
    case Point(x=x, y=0):
        print(f"Point on the x-axis at x={x}")
    case Point(x=0, y=y):
        print(f"Point on the y-axis at y={y}")
    case Point(x=x, y=y):
        print(f"Point at coordinates ({x}, {y})")
    case _:
        print("Unknown point")


Point at coordinates (2, 3)


Забележете, че трябва да подадем експлицитно имената на атрибутите. Ако искаме да използваме позиционни аргументи, то това ще работи в две ситуации:

1. Ако инстанцията е от тип `bool`, `bytearray`, `bytes`, `dict`, `float`, `frozenset`, `int`, `list`, `set`, `str`, `tuple`
2. Ако сме предифинирали метода `__match_args__`.

Повече за клас pattern-а, може да прочетете [тук](https://docs.python.org/3.11/reference/compound_stmts.html#class-patterns)

### Използване

Изпозването на `match` не е често срещано в Python. Макар и да е мощен, доста често може да бъде заместен с `if-else` блок. 

Ще покажем няколко примера за използването му, в които според нас има смисъл да се използва `match`.

С помощта на match можем да напишем програма, която проверява дали дадена дума е палиндром.

In [125]:
def palindrome_with_match(word):
    match word:
        case [a, *word, b] if a == b:
            return palindrome_with_match(word)
        case [] | [_]:
            return True
        case _:
            return False

In [126]:
words = ['aba', 'abab', 'tacocat', '', 'a']

for word in words:
    print(f'Is "{word}" palindrome ? {palindrome_with_match(list(word))}')

Is "aba" palindrome ? True
Is "abab" palindrome ? False
Is "tacocat" palindrome ? True
Is "" palindrome ? True
Is "a" palindrome ? True


In [127]:
word = "asd"

word[::-1]

'dsa'

Важно е да отбележим, че `match` не работи добре със `str`, затова се налага да превърнем думата в `list`.

(Side-note) В Python можем да проверим дали даден низ е палиндром по следния начин: `word == word[::-1]`

Друг пример е когато се налага да обработваме по-сложни колекции от данни:

In [128]:
def handle_person(data):
    match data:
        case {
            "name": {"first": first, "last": last},
            "age": age,
            "address": {"city": city, "zip": zip_code},
            "employment": {"position": "Manager"}
        }:
            return f"Manager {first} {last}, Age: {age}, City: {city}, Zip: {zip_code}"
        case {
            "name": {"first": first, "last": last},
            "age": age,
            "address": {"city": city}
        }:
            return f"{first} {last}, Age: {age}, City: {city}"
        case _:
            return "Unknown person format"

In [129]:
data_manager = {
    "name": {
        "first": "Alice",
        "last": "Johnson"
    },
    "age": 42,
    "address": {
        "city": "New York",
        "zip": "10001"
    },
    "employment": {
        "position": "Manager",
        "company": "TechCorp"
    }
}

data_employee = {
    "name": {
        "first": "Bob",
        "last": "Smith"
    },
    "age": 30,
    "address": {
        "city": "San Francisco"
    }
}
data_unknown = {
    "first_name": "Charlie",
    "age": 25,
    "city": "Los Angeles",
    "employment_status": "Unemployed"
}

print(handle_person(data_manager))
print(handle_person(data_employee))
print(handle_person(data_unknown))

Manager Alice Johnson, Age: 42, City: New York, Zip: 10001
Bob Smith, Age: 30, City: San Francisco
Unknown person format


Можем да използваме `match` и за валидация на типа на дадена променлива.

В конкретният пример ще проверяваме дали подадената променлива е `int` или `str`. Ако е `str`, ще опитаме да я превърнем в `int`.

In [130]:
def extract_value(variable):
    match variable:
        case int():
            return variable
        case str() if variable.isnumeric():
            return int(variable)
        case _:
            return None

print(extract_value("42"))
print(extract_value(5))
print(extract_value("asd"))

42
5
None


Пример от [pygrader](https://github.com/fmipython/pygrader/blob/main/grader/grader.py#L98)

In [131]:
match check:
    case ScoredCheck():
        check_result = ScoredCheckResult(check.name, 0, check.max_points)
    case NonScoredCheck():
        check_result = NonScoredCheckResult(check.name, False)
    case _:
        raise TypeError(f"Unknown check type: {type(check)}") from error

NameError: name 'check' is not defined

## Примери

Нека разгледаме някои примери за функционално програмиране от живия живот

### Пример 1


Нека е даден клас `Student` с полета `name`, `student_id_number`, `year`, `courses`, където `courses` е списък с курсове и оценки към тях, представени от класа `Course`.

Да се напише функция, която приема списък от студенти, и връща списък, съдържащ номерата на студентите, които имат среден успех над 4.50.

In [ ]:
class Course:
    def __init__(self, name='', grade=2.0):
        self.__name = name
        self.__grade = grade
    @property
    def name(self):
        return self.__name
    
    @property
    def grade(self):
        return self.__grade

    @grade.setter
    def grade(self, new_grade):
        self.__grade = new_grade

class Student:
    def __init__(self, name, student_id_number, year):
        self.__name = name
        self.__student_id_number = student_id_number
        self.__year = year
        self.__courses = []
    
    @property
    def name(self):
        return self.__name

    @property
    def student_id_number(self):
        return self.__student_id_number

    @property
    def year(self):
        return self.__year

    @property
    def courses(self):
        return self.__courses

    def start_new_year(self):
        self.__year += 1
        self.__courses = []
    
    def add_new_course(self, course):
        self.__courses.append(course)

student_1 = Student('Ivan the Programmer', '12345', 1)
student_1.add_new_course(Course('Algebra', 4.50))
student_1.add_new_course(Course('Intro to programming', 6.00))
student_1.add_new_course(Course('Geometry', 3.00))
student_1.add_new_course(Course('Calculus', 2.00))

student_2 = Student('Maria', '12346', 1)
student_2.add_new_course(Course('Algebra', 5.75))
student_2.add_new_course(Course('Intro to programming', 6.00))
student_2.add_new_course(Course('Geometry', 6.00))
student_2.add_new_course(Course('Calculus', 6.00))

student_3 = Student('Gosho from break', '12347', 1)
student_3.add_new_course(Course('Algebra', 2.00))
student_3.add_new_course(Course('Intro to programming', 2.00))
student_3.add_new_course(Course('Geometry', 2.00))
student_3.add_new_course(Course('Calculus', 3.00))


#### Решение на Пример 1

### Пример 2


Напишете декоратор, който "защитава" изпълнението на функция със специална супер секретна парола (например 'super_safe_password`). Нашият декоратор трябва да пита потребителя за парола. Ако въведената парола съвпада, изпълнява подадената функция. В противен случай, връща 'Invalid password'. 

#### Решение на пример 2

In [ ]:
@login_required
def get_super_secret_message(name):
    return f'Hi, {name}. Your mission is to learn Python.'

@login_required
def foo(a, b, c, d):
    return a + b + c + d

print(foo(2, 3, 4, d=5))

### Пример 3

`range` ни връща генератор, който ни дава числата в даден интервал. Нека разширим тази идея, и напишем генератор, който ни дава координатите в двумерно пространство при зададено начало и край.

Пример: начало - (1, 1), край - (3, 4)

Резултат: (1, 1), (1, 2), (1, 3), (2, 1), (2, 2), (2, 3)

#### Решение на Пример 3

### Пример 4

Напишете функция `bind_countries_to_capitals`, която приема два списъка - списък с имена на държави и списък с имена на столици.
Функцията трябва да върне речник, който съдържа държавите като ключове и съответните им столици като стойности. (приемаме, че на същия индекс на който е държавата стои и столицата ѝ в другия списък)

#### Решение на пример 4

### Пример 5

#### Условие 1
Даден е следният клас `RGB`, който моделира цвят в RGB формат:

In [ ]:
class RGB:
    def __init__(self, r, g, b):
        """Initialize the RGB class with the given values for red, green and blue.
        Each value should be an integer between 0 and 255.
        """

        if r < 0 or r > 255:
            raise ValueError('Invalid red value')
        if g < 0 or g > 255:
            raise ValueError('Invalid green value')
        if b < 0 or b > 255:
            raise ValueError('Invalid blue value')

        self._r = r
        self._g = g
        self._b = b

    @property
    def r(self):
        return self._r

    @property
    def g(self):
        return self._g

    @property
    def b(self):
        return self._b

    def to_hex(self):
        return f'#{self.r:02X}{self.g:02X}{self.b:02X}'
    
    @classmethod
    def from_hex(cls, hex):
        r = int(hex[1:3], base=16)
        g = int(hex[3:5], base=16)
        b = int(hex[5:7], base=16)

        return cls(r, g, b)
        
    def __repr__(self):
        return f'RGB({self.r}, {self.g}, {self.b})'

    def __eq__(self, other):
        return self.r == other.r and self.g == other.g and self.b == other.b

    def __hash__(self):
        return hash((self.r, self.g, self.b))

Да се напишат функции `rgb_pallette_to_hex_str` и `hex_str_pallette_to_rgb`, които:

* `rgb_pallette_to_hex_str`: конвертира лист от цветове като `RGB` до лист от `str` (цветовете във формат `#RRGGBB`, където `RR`, `GG`, `BB` са сътответно стойностите на червеното, зеленото и синьото в шестнадесетична бройна система)
* `hex_str_pallete_to_rgb`: конвертира лист от `str` в горепосочения hex формат (case-insensitive!) и връща лист от `RGB` обекти (цветовете в RGB формат)

***Hint 1***: съществуват начини в `str.format` или `f-string`-овете да се специфицират колко цифри и в каква бройна система да се използват при форматиране на числа

***Hint 2***: разгледайте всички варианти на конструиране на `int` по даден `str`

In [ ]:
def rgb_pallette_to_hex_str(colors):
    return [color.to_hex() for color in colors]

colors = [RGB(255, 0, 255)]

def hex_pallette_to_rgb(hex_colors):
    return [RGB.from_hex(hex_color) for hex_color in hex_colors]

result = rgb_pallette_to_hex_str(colors)
print(result)

print(hex_pallette_to_rgb(result))

#### Условие 2

Нека имаме и имена за някои от цветовете:

In [ ]:
PALLETTE = {
    RGB(255, 255, 255): 'white',
    RGB(0, 0, 0): 'black',
    RGB(255, 0, 0): 'red',
    RGB(0, 255, 0): 'green',
    RGB(0, 0, 255): 'blue',
    RGB(69, 69, 69): "the 51st shade of grey",
}

In [ ]:
hex_colors = ["#696969", "#00FF00", "#AAAAAA"]

def extract_only_named_colors(hex_colors):
    # 1. Convert hex to RGB objects
    # 2. Check if each RGB object is in Pallette
    # 3. Return the names those who are in Pallette

    rgb_objects = hex_pallette_to_rgb(hex_colors)
    filtered_objects = [rgb_object for rgb_object in rgb_objects if rgb_object in PALLETTE]
    names_of_filtered_objects = [PALLETTE[filtered_object] for filtered_object in filtered_objects]

    return names_of_filtered_objects

Да се напише функция `extract_only_named_colors` по подаден списък от цветове във формат `#RRGGBB` връща списък от имената им (само на тези, които присъстват в `PALLETTE` - другите се игнорират).

### Пример 6

Рефакторирайте долния код така, че да съответства на функционалния стил на програмиране:

In [ ]:
class PrettyPrint:
    def __init__(self):
        self.__border = '|'
        self.__content = ''
        self.__prefix = '***'
        self.__suffix = '***'

    def pretty_print(self):
        return f'{self.__border} {self.__prefix} {self.__content} {self.__suffix} {self.__border}'

    @property
    def border(self):
        return self.__border

    @border.setter
    def border(self, new_border):
        self.__border = new_border

    @property
    def content(self):
        return self.__content

    @content.setter
    def content(self, new_content):
        self.__content = new_content

    @property
    def prefix(self):
        return self.__prefix

    @prefix.setter
    def prefix(self, new_prefix):
        self.__prefix = new_prefix

    @property
    def suffix(self):
        return self.__suffix

    @suffix.setter
    def suffix(self, new_suffix):
        self.__suffix = new_suffix

pretty_printer = PrettyPrint()

pretty_printer.content = 'Hello world'
print(pretty_printer.pretty_print())

pretty_printer.prefix = '<<<'
pretty_printer.suffix = '>>>'
print(pretty_printer.pretty_print())

### Пример 7

Направете преводач от кирилица към "шльокавица".

Нека приемем, че азбуката на шльокавицата e A, B, V, G, D, E, J, Z, I, Y, K, L, M, N, O, P, R, S, T, U, F, H, C, 4, 6, 6T, U, Y, YU, Q.

### Пример 8

Напишете собствена версия на `enumerate`. Тя трябва да приема като аргументи колекцията, по която ще итерираме, както и незадължителен аргумент `start` (=0).

In [ ]:
def my_enumerate(collection, start=0):
    pass

### Пример 9

В шахa, конят се движи по един от следните начини:
- две полета хоризонтално и едно вертикално
- две полета вертикално и едно хоризонтално

<img src="https://i.imgur.com/jRvOJaK.png" style="width: 25%"/>


Напомняме, че редовете се номерират от 1 до 8, а колоните - от A до H. 
В случая, нашият кон е на позиция `d4`.
Той може да се премести на следните позиции: `e7`, `f6`, `f4`, `e3`, `c3`, `b4`, `b6`, `c7`

Напишете генератор, който приема начална позиция на кон, и връща всички възможни ходове.

In [ ]:
# Write your code here:

column_name_to_number = {letter: number for number, letter in enumerate("abcdefgh", start=1)}
column_number_to_name = {number: letter for number, letter in enumerate("abcdefgh", start=1)}

possible_offsets = [-2, -1, 1, 2]
offsets = [
    (offset_x, offset_y) 
    for offset_x in possible_offsets 
    for offset_y in possible_offsets
    if abs(offset_x) != abs(offset_y)
]

def possible_moves(column, row):
    column_as_number = column_name_to_number[column]
    moves = [
        new_move
        for offset in offsets
        if is_move_valid((new_move := move_knight((column_as_number, row), offset)))
    ]

    moves = (
        (column_number_to_name[column], row)
        for (column, row) in moves
    )
    
    return moves

def move_knight(current_position, offset):
    column, row = current_position
    offset_column, offset_row = offset

    return column + offset_column, row + offset_row

def is_move_valid(current_position):
    column, row = current_position

    return 1 <= column <= 8 and 1 <= row <= 8


possible_moves('a', 1)

In [ ]:

# 2 possible moves
assert set(possible_moves('a', 1)) == {('c', 2), ('b', 3)}
assert set(possible_moves('h', 1)) == {('f', 2), ('g', 3)}
assert set(possible_moves('h', 8)) == {('f', 7), ('g', 6)}
assert set(possible_moves('a', 8)) == {('c', 7), ('b', 6)}

# 3 possible moves
assert set(possible_moves('a', 2)) == {('c', 3), ('b', 4), ('c', 1)}
assert set(possible_moves('a', 7)) == {('c', 6), ('b', 5), ('c', 8)}
assert set(possible_moves('h', 2)) == {('g', 4), ('f', 1), ('f', 3)}
assert set(possible_moves('h', 7)) == {('f', 6), ('g', 5), ('f', 8)}

# 4 possible moves
assert set(possible_moves('a', 3)) == {('c', 4), ('b', 5), ('b', 1), ('c', 2)}
assert set(possible_moves('h', 6)) == {('g', 8), ('f', 5), ('g', 4), ('f', 7)}
assert set(possible_moves('g', 2)) == {('e', 1), ('f', 4), ('h', 4), ('e', 3)}

# 6 possible moves
assert set(possible_moves('b', 3)) == {('c', 5), ('d', 2), ('c', 1), ('d', 4), ('a', 5), ('a', 1)}
assert set(possible_moves('g', 6)) == {('f', 4), ('h', 4), ('e', 5), ('e', 7), ('h', 8), ('f', 8)}

# 8 possible moves
assert set(possible_moves('d', 4)) == {('b', 3), ('b', 5), ('c', 2), ('c', 6), ('e', 2), ('e', 6), ('f', 3), ('f', 5)}
assert set(possible_moves('f', 6)) == {('h', 7), ('g', 8), ('e', 8), ('g', 4), ('d', 5), ('e', 4), ('h', 5), ('d', 7)}

# Generator tests
for move in possible_moves('a', 1):
    assert move in {('c', 2), ('b', 3)}

generator = possible_moves('a', 1)
assert next(generator) in {('c', 2), ('b', 3)}
assert next(generator) in {('c', 2), ('b', 3)}

try:
    next(generator)
    assert False
except StopIteration:
    pass

print("✅ All OK")

### Пример 10

В езикът Rust съществува функция на име [take](https://doc.rust-lang.org/std/iter/trait.Iterator.html#method.take).

Тя работи върху итератор, и връща нов итератор, с първите `n` елемента от него (или всички елементи, ако итератора е по-къс от `n`).

В Python нямаме такава функция, затова нека си напишем една.

Нашата Python имплементация ще приема два аргумента - `iterable` (итеруемото, от което ще взимаме елементи) и `n` (броят елементи, които ще вземем).
Тя ще връща нов **генератор**, който ще съдържа само първите `n` елемента от `iterable` (или всички, ако дължината на `iterable` е под `n`).

Ако `n` е отрицалтелно, нека се върне генератор с последните `n` елемента.

In [ ]:
# Write your code here
def take(iterable, n):
    if n >= 0:
        for i in range(n):
            yield next(iterable)
    else:
        return (item for item in iterable[n:])

In [ ]:
sample = [1, 2, 3, 4, 5, 6]

expected_1 = [1, 2, 3]
actual_1 = list(take(sample, 3))

expected_2 = []
actual_2 = list(take(sample, 0))

expected_3 = [1, 2, 3, 4, 5, 6]
actual_3 = list(take(sample, 10))

expected_4 = [1, 2, 3, 4]
actual_4 = list(take(sample, 4))

expected_5 = [5, 6]
actual_5 = list(take(sample, -2))

expected_6 = [3, 4, 5, 6]
actual_6 = list(take(sample, -4))

assert expected_1 == actual_1
assert expected_2 == actual_2
assert expected_3 == actual_3
assert expected_4 == actual_4
assert expected_5 == actual_5
assert expected_6 == actual_6

print("✅ All OK")

### Пример 11

За ефективна работа с изображения, тяхното представяне много често е във вид на матрица.
Целта на тази задача е да се имплементират няколко прости операции върху изображения (матрици). 

За улеснение, матрица дефинираме като двумерен списък с размер `MxN` (`M` реда, и `N` колони) и елементи цели числа.

Напишете следните функции, които модифицират даден матрица:

- `rotate_clockwise` - завърта матрицата в посока на часовниковата стрелка
- `rotate_counterclockwise` - завърта матрицата в посока обратна на часовниковата стрелка
- `flip_horizontal` - връща огледална матрица, в хоризонтална посока
- `flip_vertical` - връща огледална матрица, във вертикална посока


Или казано по друг начин:

$$ A = \begin{pmatrix}1 & 2 & 3\\ 4 & 5 & 6\\ 7 & 8 & 9\end{pmatrix} $$

$$ rotate\_clockwise(A) = \begin{pmatrix}7 & 4 & 1\\ 8 & 5 & 2\\ 9 & 6 & 3\end{pmatrix} $$
$$ rotate\_counterclockwise(A) = \begin{pmatrix}3 & 6 & 9\\ 2 & 5 & 8\\ 1 & 4 & 7\end{pmatrix} $$
$$ flip\_horizontal(A) = \begin{pmatrix}3 & 2 & 1\\ 6 & 5 & 4\\ 9 & 8 & 7\end{pmatrix} $$
$$ flip\_vertical(A) = \begin{pmatrix}7 & 8 & 9\\ 4 & 5 & 6\\ 1 & 2 & 3\end{pmatrix} $$

Hint 1: Всяка една от четирите функции може да се напише на един ред.

In [ ]:
l = [1, 2, 3]

list(reversed(l))

In [ ]:
# Use this for debugging, if needed
def pretty_print(matrix):
    print('-' * (len(matrix[0]) * 2 - 1))
    for row in matrix:
        print(' '.join(str(item) for item in row))
    print('-' * (len(matrix[0]) * 2 - 1))


def get_column(matrix, column):
    pass

def rotate_clockwise(matrix):
    pass

def rotate_counterclockwise(matrix):
    pass

def flip_horizontal(matrix):
    pass

def flip_vertical(matrix):
    pass

In [ ]:
matrix_1 = [[1, 2, 3], [4, 5, 6], [7, 8, 9]]

expected_clockwise_1 = [[7, 4, 1], [8, 5, 2], [9, 6, 3]]
expected_counterclockwise_1 = [[3, 6, 9], [2, 5, 8], [1, 4, 7]]
expected_flip_horizontal_1 = [[3, 2, 1], [6, 5, 4], [9, 8, 7]]
expected_flip_vertical_1 = [[7, 8, 9], [4, 5, 6], [1, 2, 3]]


assert rotate_clockwise(matrix_1) == expected_clockwise_1
assert rotate_counterclockwise(matrix_1) == expected_counterclockwise_1

assert flip_horizontal(matrix_1) == expected_flip_horizontal_1
assert flip_vertical(matrix_1) == expected_flip_vertical_1


matrix_2 = [[1, 2], [3, 4], [5, 6], [7, 8]]

expected_clockwise_2 = [[7, 5, 3, 1], [8, 6, 4, 2]]
expected_counterclockwise_2 = [[2, 4, 6, 8], [1, 3, 5, 7]]
expected_flip_horizontal_2 = [[2, 1], [4, 3], [6, 5], [8, 7]]
expected_flip_vertical_2 = [[7, 8], [5, 6], [3, 4], [1, 2]]

assert rotate_clockwise(matrix_2) == expected_clockwise_2
assert rotate_counterclockwise(matrix_2) == expected_counterclockwise_2
assert flip_horizontal(matrix_2) == expected_flip_horizontal_2
assert flip_vertical(matrix_2) == expected_flip_vertical_2


matrix_3 = [[1, 2, 3], [4, 5, 6]]

expected_clockwise_3 = [[4, 1], [5, 2], [6, 3]]
expected_counterclockwise_3 = [[3, 6], [2, 5], [1, 4]]
expected_flip_horizontal_3 = [[3, 2, 1], [6, 5, 4]]
expected_flip_vertical_3 = [[4, 5, 6], [1, 2, 3]]

assert rotate_clockwise(matrix_3) == expected_clockwise_3
assert rotate_counterclockwise(matrix_3) == expected_counterclockwise_3
assert flip_horizontal(matrix_3) == expected_flip_horizontal_3
assert flip_vertical(matrix_3) == expected_flip_vertical_3

print("✅ All OK")